### Data Normalization — NCT-CRC-HE-100K

The last notebook gave us a good understadning of the data structure and training cohorts. 

This notebook address the issue posed by the channel stats where in different cohorts the intensity varies and is not cross comparable. 

In [1]:
from pathlib import Path
import src.stain_norm as sn
import src.class_sampling as cs
import src.utilities.viz as viz

## Manceko normalization

Implemented a simple reusable function in `src/stain_norm.py` file that can take a image path and normalize the image to a reference image specified in the cell below.

### Cohort description

Two cohorts are used throughout the project:

- **NCT-CRC-HE-100K-NONORM** — 100,000 tiles, 224×224 px at 0.5 MPP, nine tissue classes, drawn from N=86 H&E slides (NCT Heidelberg and UMM Mannheim). Used for training. The NONORM variant is used deliberately: the default distribution is already Macenko-normalized, which would confound any measurement of what normalization contributes.
- **CRC-VAL-HE-7K** — 7,180 tiles from N=50 patients with no overlap with the training cohort. Held out as the external evaluation set.

CRC-VAL is a held-out patient cohort: its tissue also originates from the NCT tissue bank, which contributed to the training cohort. Generalization claims are scoped accordingly.

A **balanced sample of 1,250 tiles per class** is drawn from NCT (1,000 train + 250 validation). **All 7,180 CRC-VAL tiles** are used; the cohort is small and evaluated once, so subsampling would only widen confidence intervals. Class imbalance in CRC-VAL is handled by **balanced accuracy and macro-F1 rather than by subsampling**.

Each cohort is written to a manifest CSV recording every tile path, its class, and its rank within a fixed per-class permutation. The manifest — not the random seed — is the artifact of record: it is **hashed, committed, and every cached feature matrix** is keyed to it. Rank makes the **train/validation split and the label-efficiency budgets deterministic thresholds** rather than fresh draws, so subsets nest by construction.

### Known limitation

NCT tile filenames carry no slide or patient identifier, so tiles cannot be grouped by slide of origin. With roughly 1,160 tiles per slide, any split of this cohort places tiles from the same slide on both sides. The in-distribution validation figure is therefore a tuning signal only; the generalization claim rests on CRC-VAL.

In [2]:

NCT = Path("data/NCT-CRC-HE-100K-NONORM")
CRC = Path("data/CRC-VAL-HE-7K")

# NCT: 1250/class = 1000 train + 250 val. 1000 is the top of the label-efficiency
# CRC: all 7K validation tiles, no sampling

train_pool = cs.sample_cohort(NCT, n_per_class=1250, seed=42, strict=True)
mf_nct, sha_nct = cs.write_manifest(
    train_pool, "manifests/nct_1250", NCT,
    {"seed": 42, "n_per_class": 1250, "exclude_classes": "()", "pattern": "*.tif"})
validation_pool = cs.sample_cohort(CRC, n_per_class=None, seed=42)
mf_crc, sha_crc = cs.write_manifest(
    validation_pool, "manifests/crcval_all", CRC,
    {"seed": 42, "n_per_class": "None", "exclude_classes": "()", "pattern": "*.tif"})

### Fitting and freezing the Macenko target

Macenko normalization maps a tile's estimated stain basis onto a reference basis. The reference used here is a virtual target: stain vectors are estimated per tile across the training split and combined by elementwise median, with column unit-norm restored afterwards. A median over many tiles is preferred to a single reference image, whose idiosyncrasies would otherwise propagate to every normalized tile in the project.

The target is fitted on training tiles only, excluding BACK. Background tiles are near-white, and the tissue-fraction guard rejects them; excluding the class avoids reading 1,250 tiles that would all be discarded. Restricting to training ranks keeps validation tiles out of the fit — the target is only eight numbers and unsupervised, so the exposure would be minimal.

The target is persisted as those eight numbers (HERef, 3×2, and maxCRef, length 2); the tiles it was fitted on are disposable. Once written, the target is frozen. If it changes after any feature extraction has run, part of the benchmark matrix sits in a different preprocessing condition with nothing to signal the discrepancy. The cell is guarded so re-execution reloads rather than refits.

The same target is applied to both cohorts. Normalizing each cohort to its own median would align each to a different reference and leave the two no closer to each other, which is the opposite of the intent

In [3]:
target_path = Path("notebooks/output/macenko_target_nct100k.npz")
if target_path.exists():
    records, _ = cs.read_manifest("manifests/nct_1250.csv", NCT)
    tiles = [r["path"] for r in records]
    crc_tiles = [r["path"] for r in cs.read_manifest("manifests/crcval_all.csv", CRC)[0]]
    normalizer = sn.load_normalizer_target(target_path)
    print(f"loaded frozen target from {target_path}")
else:
    # Fitted on train tiles only, BACK excluded: pure background yields
    # degenerate stain vectors that poison the elementwise median. 8,000 tiles.
    records, _ = cs.read_manifest("manifests/nct_1250.csv", NCT)
    tiles = [r["path"] for r in records]
    crc_tiles = [r["path"] for r in cs.read_manifest("manifests/crcval_all.csv", CRC)[0]]
    train_rows, _ = cs.split_train_val(records, 1000, 250)
    fit_paths = [records[i]["path"] for i in train_rows
                 if records[i]["label"] != "BACK"]
    normalizer = sn.estimate_median_target(fit_paths, max_workers=8)
    sn.save_normalizer_target(normalizer, target_path.with_suffix(""))
    print(f"fitted and froze target on {len(fit_paths)} tiles")

loaded frozen target from notebooks\output\macenko_target_nct100k.npz


### Tile appearance by cohort and class

Sample tiles from both cohorts, selected by rank from the manifests so the images shown are the images processed rather than an independent draw.

Each caption reports the tile's tissue fraction the proportion of pixels whose optical density exceeds the threshold used for stain estimation. This is the quantity the normalization guard thresholds at 0.25, so the figure and the rejection counts below are two views of the same measurement.

In [4]:
nct_records, _ = cs.read_manifest("manifests/nct_1250.csv", NCT)
crc_records, _ = cs.read_manifest("manifests/crcval_all.csv", CRC)

cohorts = {"NCT-NONORM": nct_records, "CRC-VAL": crc_records}

samples, captions = viz.load_manifest_samples(
    cohorts, classes=["ADI", "BACK", "DEB","LYM","MUC","MUS","NORM","STR","TUM"], n_samples=5,
    annotate=sn.tissue_fraction)

viz.plot_interactive_class_grid(
    samples, n_samples=5, captions=captions,
    title_prefix="Tile · caption = tissue fraction (guard threshold 0.25)").show()

print(viz.summarize_tissue_fraction(samples, sn.tissue_fraction))

                   n    min  median    max
group                                     
NCT-NONORM - ADI   5  0.015   0.028  0.029
NCT-NONORM - BACK  5  0.000   0.002  0.011
NCT-NONORM - DEB   5  0.400   0.758  0.864
NCT-NONORM - LYM   5  0.761   0.949  0.993
NCT-NONORM - MUC   5  0.227   0.257  0.772
NCT-NONORM - MUS   5  0.244   0.605  0.799
NCT-NONORM - NORM  5  0.169   0.778  0.955
NCT-NONORM - STR   5  0.344   0.485  0.772
NCT-NONORM - TUM   5  0.262   0.746  0.979
CRC-VAL - ADI      5  0.056   0.149  0.218
CRC-VAL - BACK     5  1.000   1.000  1.000
CRC-VAL - DEB      5  0.032   0.684  0.901
CRC-VAL - LYM      5  0.267   0.762  0.858
CRC-VAL - MUC      5  0.208   0.581  0.862
CRC-VAL - MUS      5  0.499   0.703  0.804
CRC-VAL - NORM     5  0.474   0.562  0.732
CRC-VAL - STR      5  0.333   0.344  0.792
CRC-VAL - TUM      5  0.488   0.650  0.858


### Paired channel statistics and rejection accounting

Per-class, per-channel mean and standard deviation for raw and normalized tiles, computed over the same tiles. 

Computing the two passes independently would allow them to diverge on membership: the normalized pass drops tiles Macenko rejects, the raw pass would keep them, and the resulting variance reduction would partly measure the removal of background tiles rather than any effect of normalization.

Rejections are binned by cause. Low tissue means the guard declined to normalize a tile with insufficient stain content — the intended behaviour on background and adipose. An exception on a tile that passed the guard would indicate a different problem and is counted separately.

The guard is applied before stain estimation rather than as exception handling. On a near-white tile the decomposition usually succeeds, returning an arbitrary basis spanning numerical noise, and produces a plausible-looking image from a meaningless transform. That failure raises nothing and cannot be caught after the fact.

Rejection rates are reported alongside every downstream result: in the normalized condition, rejected tiles fall back to raw, so the normalized and raw conditions are identical for any class with a high rejection rate.

In [5]:
nct_raw, nct_norm = sn.compute_paired_channel_stats(NCT, normalizer, paths=tiles)
crc_raw, crc_norm = sn.compute_paired_channel_stats(CRC, normalizer, paths=crc_tiles)

print(sn.failure_table(nct_raw))
print(sn.failure_table(crc_raw))
sn.save_stats("notebooks/output/paired_stats", nct_raw=nct_raw, nct_norm=nct_norm,
              crc_raw=crc_raw, crc_norm=crc_norm)

ADI    n=   18 rejected= 1232 low tissue=1232
BACK   n=   16 rejected= 1234 low tissue=1234
DEB    n= 1150 rejected=  100 low tissue=100
LYM    n= 1250 rejected=    0 
MUC    n=  987 rejected=  263 low tissue=263
MUS    n=  947 rejected=  303 low tissue=303
NORM   n= 1201 rejected=   49 low tissue=49
STR    n= 1049 rejected=  201 low tissue=201
TUM    n= 1239 rejected=   11 low tissue=11
ADI    n=   43 rejected= 1295 low tissue=1295
BACK   n=  847 rejected=    0 
DEB    n=  170 rejected=  169 low tissue=169
LYM    n=  631 rejected=    3 low tissue=3
MUC    n=  944 rejected=   91 low tissue=91
MUS    n=  592 rejected=    0 
NORM   n=  736 rejected=    5 low tissue=5
STR    n=  421 rejected=    0 
TUM    n= 1230 rejected=    3 low tissue=3
       n_used  n_rejected  reject_pct  low tissue
class                                            
ADI        18        1232        98.6      1232.0
BACK       16        1234        98.7      1234.0
DEB      1150         100         8.0       100.0
LY

WindowsPath('notebooks/output/paired_stats.json')

### Interactive review of rejected and borderline tiles (napari)

The failure table gives counts; this cell opens the tiles behind them. Raw and normalized versions sit side by side under one slider, and the overlay shows class, manifest rank, tissue fraction and the rejection reason.

Two groups are worth looking at:

- **Rejected:** tiles the guard declined. They fall back to raw downstream, so they are shown with an empty (black) normalized slot rather than a copy of the raw tile.
- **Borderline:** tiles accepted with a tissue fraction just above the 0.25 guard. These are the most likely to carry a plausible-looking stain transform estimated from very little stain.

Tiles are taken in manifest rank order, so the ones reviewed are the ones processed. To see the BACK asymmetry, set `REVIEW_COHORT = "CRC-VAL"`, `REVIEW_CLASSES = ["BACK"]`, and add `"accepted"` to `REVIEW_KEEP`: every CRC-VAL background tile passes the guard.

Requires a local Qt display. This is not a headless step, and it should not be part of a top-to-bottom acceptance run.

In [ ]:
%gui qt
from collections import Counter
import numpy as np
import napari

REVIEW_COHORT = "NCT-NONORM"            # or "CRC-VAL"
REVIEW_CLASSES = ["ADI", "BACK", "DEB", "LYM", "MUC", "MUS", "NORM", "STR", "TUM"]
REVIEW_KEEP = ("rejected", "borderline")  # add "accepted" to see passing tiles
REVIEW_MAX_PER_CLASS = 25
BORDERLINE = (0.25, 0.35)               # guard threshold .. upper edge of "just passed"


def collect_review_tiles(records, normalizer, classes, keep, max_per_class, borderline):
    """
    Raw/normalized pairs for tiles worth inspecting, in manifest rank order.

    Kept free of any viewer code so the selection can be checked or reused
    without a display. Returns (raw_stack, norm_stack, meta), stacks shaped
    (n, H, W, 3) uint8, meta one dict per tile.
    """
    raws, norms, meta = [], [], []
    for cls in classes:
        rows = sorted((r for r in records if r["label"] == cls), key=lambda r: r["rank"])
        n = 0
        for r in rows:
            if n >= max_per_class:
                break
            raw = sn.load_image_array(r["path"])
            frac = sn.tissue_fraction(raw)
            norm, reason = sn.normalize_array(raw, normalizer)
            if norm is None:
                status = "rejected"
            elif frac < borderline[1]:
                status = "borderline"
            else:
                status = "accepted"
            if status not in keep:
                continue
            raws.append(raw)
            # Black slot, not the raw tile: downstream a rejected tile falls back
            # to raw, and showing raw twice would hide that nothing was normalized.
            norms.append(norm if norm is not None else np.zeros_like(raw))
            meta.append({"label": cls, "rank": r["rank"], "frac": frac,
                         "status": status, "reason": reason or "",
                         "file": Path(r["path"]).name})
            n += 1
    if not raws:
        raise ValueError(f"No tiles matched keep={keep} for classes={classes}")
    return np.stack(raws), np.stack(norms), meta


raw_stack, norm_stack, review_meta = collect_review_tiles(
    cohorts[REVIEW_COHORT], normalizer, REVIEW_CLASSES,
    keep=REVIEW_KEEP, max_per_class=REVIEW_MAX_PER_CLASS, borderline=BORDERLINE)
print(Counter(f"{m['label']:5s} {m['status']}" for m in review_meta))

viewer = napari.Viewer(title=f"Macenko review: {REVIEW_COHORT}")
viewer.add_image(raw_stack, rgb=True, name="raw")
viewer.add_image(norm_stack, rgb=True, name="normalized")
viewer.grid.enabled = True          # raw | normalized, one shared tile slider
viewer.text_overlay.visible = True


def _update_caption(event=None):
    m = review_meta[viewer.dims.current_step[0]]
    viewer.text_overlay.text = (f"{m['label']}  rank {m['rank']}  tissue {m['frac']:.2f}  "
                                f"{m['status']}  {m['reason']}\n{m['file']}")


viewer.dims.events.current_step.connect(_update_caption)
_update_caption()

### Within-cohort effect of normalization

Percentage reduction in per-channel standard deviation after normalization, by class. Positive values indicate a tightened intensity distribution.

Classes with no successfully normalized tiles are excluded: their statistics are undefined by construction, and their rejection counts are reported in the failure table above instead.

This figure characterises the effect of normalization within a cohort. It does not address whether normalization reduces the difference between cohorts, which is the question the project actually depends on and is measured separately below.

In [11]:
reduction = sn.compute_variance_reduction(nct_raw, nct_norm)
sn.plot_variance_reduction(reduction).show()
sn.plot_channel_stats_comparison(nct_raw, nct_norm).show()

### Qualitative before/after comparison

Paired raw and normalized tiles per class. 

Included as a sanity check on the fitted target: normalized tiles should show a consistent stain profile across classes while retaining the morphological differences that distinguish them. 

Convergence of all classes to a single appearance would indicate the transform is destroying signal rather than harmonising it.

In [12]:
grid_data = sn.collect_normalized_grid_data(NCT, normalizer, n_samples=3)
sn.plot_grid_from_data(grid_data)

### CRC-VAL stain profile — characterisation, not preprocessing

A Macenko target is fitted on CRC-VAL. This is not used as a preprocessing step: CRC-VAL is normalized with the NCT-fitted target so that both cohorts are mapped onto a common reference.

Its purpose is analytical. The profile characterises the second cohort's stain distribution, and it serves as the donor profile for the stain-swap counterfactual: correctly classified tiles are re-normalized to this profile and the change in prediction is measured. A high flip rate indicates a model driven by stain rather than morphology.

Saved separately as a profile to keep it distinct from the frozen preprocessing target.

In [13]:
reduction_crc = sn.compute_variance_reduction(crc_raw, crc_norm)
sn.plot_variance_reduction(reduction_crc,
    title="Std reduction, CRC-VAL (already Macenko-normalized at source)").show()
sn.plot_channel_stats_comparison(crc_raw, crc_norm).show()

### Cross-cohort colour shift

Euclidean distance between the per-class mean RGB vectors of the two cohorts, before and after normalization with the shared NCT-fitted target.

This is the measurement the preprocessing arm of the benchmark rests on. If normalization reduces cohort-specific variation, the normalized distances should be smaller than the raw distances for classes where normalization was actually applied. Classes with high rejection rates fall back to raw tiles and are expected to show no change; they are labelled rather than removed.

In [14]:
raw_shift  = viz.compute_cross_cohort_color_shift(nct_raw, crc_raw)
norm_shift = viz.compute_cross_cohort_color_shift(nct_norm, crc_norm)

import pandas as pd
shift = pd.DataFrame({"raw": raw_shift, "normalized": norm_shift})
shift["reduction_pct"] = (100 * (shift["raw"] - shift["normalized"]) / shift["raw"]).round(1)
shift["nct_reject_pct"] = sn.failure_table(nct_raw)["reject_pct"]
shift["crc_reject_pct"] = sn.failure_table(crc_raw)["reject_pct"]
print(shift.round(2))
viz.plot_color_shift(raw_shift, title="Cross-cohort mean colour distance — raw").show()
viz.plot_color_shift(norm_shift, title="Cross-cohort mean colour distance — normalized").show()

         raw  normalized  reduction_pct  nct_reject_pct  crc_reject_pct
ADI    20.88        1.18           94.4            98.6            96.8
BACK  131.52       68.64           47.8            98.7             0.0
DEB    21.01        4.09           80.5             8.0            49.9
LYM   112.29       26.26           76.6             0.0             0.5
MUC    15.09        5.80           61.5            21.0             8.8
MUS    14.99       21.07          -40.6            24.2             0.0
NORM   39.98       10.90           72.7             3.9             0.7
STR    11.96        6.98           41.7            16.1             0.0
TUM    12.26        5.97           51.3             0.9             0.2


## Summary

This notebook fits and freezes a Macenko stain-normalization target on the training cohort, applies it to both cohorts, and quantifies its effect within and between them.

###  Key Findings & Observations
1. **Macenko Normalization Reduces Color Variance:**

   Normalization reduces within-cohort channel variance for classes with sufficient stain content, consistent with attenuation of slide-to-slide staining variability.

   Macenko is inapplicable to two of the nine classes. ADI (adipose) is rejected at 98.6% in NCT and 96.8% in CRC-VAL: adipose tissue is predominantly membrane and unstained space, so the tissue fraction falls below the threshold required for stain estimation. BACK is rejected at 98.7% in NCT. Rejected tiles fall back to raw, so for these classes the normalized and raw conditions are identical. This is a property of the method's applicability, not a defect of the implementation, and it dilutes any macro-averaged normalization effect across nine classes.

2. **Class-specific Behaviours:**

   CRC-VAL-HE-7K is distributed in a Macenko-normalized form, per the Zenodo record. Its background tiles are dark rather than near-white and are rejected at 0%, in contrast to 98.7% in the un-normalized training cohort. This is consistent with normalization having been applied to background tiles without a tissue-content guard, which produces a plausible-looking image from an ill-determined stain basis. The published tiles were not regenerated here, so the mechanism is inferred from tile appearance and tissue-fraction statistics rather than observed directly. 

   BACK class die t0 identified reasosns would perform the worst per-class result on CRC-VAL as these tiles are supplied normalized however adding noise.

### Conclusions
The "raw" condition compares un-normalized training tiles against pre-normalized evaluation tiles; it remains the correct baseline but is labelled as asymmetric wherever reported. BACK constitutes a genuine distribution shift between cohorts with an identified mechanism, and is predicted to be the worst-performing class on external evaluation. All nine classes are retained: excluding them would break comparability with the published benchmark and discard the most informative failure case in the dataset.


---


### Summary: 

| Aspect | Raw (NONORM) | Macenko-normalized |
| :--- | :--- | :--- |
| **Reference target** | — | Virtual median target over 6,267 training tiles (8 persisted numbers: `HERef` 3×2, `maxCRef` 2). Not a single reference tile, whose idiosyncrasies would propagate to every normalized patch. |
| **Applicability** | All tiles | 69.8% of NCT tiles, 78.2% of CRC-VAL tiles. Remainder falls back to raw. |
| **Within-cohort channel σ (NCT)** | baseline | `[fill: mean % change, 7 normalizable classes]` |
| **Within-cohort channel σ (CRC-VAL)** | baseline | Negative (σ increases). Expected: CRC-VAL arrives Macenko-normalized, so per-tile re-estimation adds noise rather than removing variation. |
| **Cross-cohort mean-colour distance** | `[fill: mean over classes]` | `[fill]` — the measurement the preprocessing arm rests on |
| **Effect on benchmark** | Un-normalized train vs. pre-normalized test — asymmetric baseline, labelled as such | Both cohorts mapped to one reference; 7 of 9 classes affected |

### Rejection by class — where normalization was actually applied

| Class | NCT rejected | CRC-VAL rejected | Interpretation |
| :--- | ---: | ---: | :--- |
| **ADI** | 98.6% | 96.8% | Adi is predominantly membrane and unstained space; tissue fraction below threshold in both cohorts. Macenko inapplicable. |
| **BACK** | 98.7% | **0%** | The asymmetry. NCT background is near-white and correctly declined; CRC-VAL background exceeds the tissue threshold on every tile. |
| **DEB** | 8.0% | 49.9% | Same asymmetry at lower amplitude. |
| **MUS** | 24.2% | 0% | . |
| **MUC** | 21.0% | 8.8% | . |
| **STR** | 16.1% | 0% | . |
| **NORM** | 3.9% | 0.7% | . |
| **TUM** | 0.9% | 0.2% | . |
| **LYM** | 0.0% | 0.5% | Dense nuclei, highest optical density. |
| **Overall** | **30.2%** | **21.8%** | . |

---

### 🔑 Next Steps for the Pipeline

- **Feature Extraction:** Pass the normalized patches into foundational pathology encoders H-optimus-0 to extract domain-invariant embeddings for classification on the `CRC-VAL-HE-7K` evaluation set.